# Depth + Structure Guided Real-ESRGAN

한 장의 입력 이미지에 대해 다음 4가지를 비교합니다.

1. Original input
2. Lanczos x4 upsampling
3. Real-ESRGAN x4
4. Proposed: Depth + Structure 기반 adaptive fusion

최종 출력:

`I_final = W * I_sr + (1 - W) * I_up`

- 가까운 영역: Real-ESRGAN 비중을 높게 유지
- 가까운 + 구조적 영역: 거의 Real-ESRGAN 100%
- 매우 가까운 영역: 구조 여부와 무관하게 Real-ESRGAN 100%
- 먼 영역이라도 구조가 강하면 Real-ESRGAN 비중을 일정 수준 유지


## 실행 방법

이 노트북은 **Depth Anything V2 Small (Hugging Face) + Real-ESRGAN x4plus**를 사용합니다.

셀을 위에서 아래로 순서대로 실행하세요. NumPy/SciPy/pycolmap/Depth Anything 3는 사용하지 않습니다.


In [ ]:
import sys
sys.path.insert(0, "/content/Real-ESRGAN")

In [ ]:
!pip install -U setuptools wheel cython
%cd /content

!rm -rf BasicSR
!git clone https://github.com/XPixelGroup/BasicSR.git

/content
Cloning into 'BasicSR'...
remote: Enumerating objects: 5924, done.
remote: Total 5924 (delta 0), reused 0 (delta 0), pack-reused 5924 (from 1)
Receiving objects: 100% (5924/5924), 4.14 MiB | 5.43 MiB/s, done.
Resolving deltas: 100% (3759/3759), done.


In [ ]:
import sys
import types
import torchvision.transforms.functional as F

module_name = "torchvision.transforms.functional_tensor"

if module_name not in sys.modules:
    mod = types.ModuleType(module_name)
    mod.rgb_to_grayscale = F.rgb_to_grayscale
    sys.modules[module_name] = mod

In [ ]:
import sys

sys.path.insert(0, "/content/BasicSR")
sys.path.insert(0, "/content/Real-ESRGAN")

print(sys.path[:3])
from pathlib import Path

version_file = Path("/content/BasicSR/basicsr/version.py")

version_file.write_text(
    """
__version__ = "1.4.2"
__gitsha__ = "unknown"
version_info = (1, 4, 2)
""".strip()
)

print("created:", version_file)

from basicsr.archs.rrdbnet_arch import RRDBNet

print("BasicSR import OK")

['/content/Real-ESRGAN', '/content/BasicSR', '/content/Real-ESRGAN']
created: /content/BasicSR/basicsr/version.py
BasicSR import OK


In [ ]:
import sys

sys.path.insert(0, "/content/BasicSR")
sys.path.insert(0, "/content/Real-ESRGAN")

print(sys.path[:3])
from pathlib import Path

['/content/Real-ESRGAN', '/content/BasicSR', '/content/Real-ESRGAN']


In [ ]:
import sys
import types
import torchvision.transforms.functional as F

module_name = "torchvision.transforms.functional_tensor"

if module_name not in sys.modules:
    mod = types.ModuleType(module_name)
    mod.rgb_to_grayscale = F.rgb_to_grayscale
    sys.modules[module_name] = mod

print("torchvision compatibility patch OK")

torchvision compatibility patch OK


In [ ]:
# ============================================================
# Real-ESRGAN local repo를 현재 Python 환경에 등록
# dependencies는 설치하지 않음
# ============================================================

%cd /content/Real-ESRGAN

!python -m pip install -e . --no-deps

# ============================================================
# Import cache 초기화 + 확인
# ============================================================

import sys
import importlib
import types

importlib.invalidate_caches()

# 혹시 이전 실패 import 흔적 제거
for name in list(sys.modules.keys()):
    if name == "realesrgan" or name.startswith("realesrgan."):
        del sys.modules[name]


# torchvision compatibility patch
import torchvision.transforms.functional as TF

module_name = "torchvision.transforms.functional_tensor"

mod = types.ModuleType(module_name)
mod.rgb_to_grayscale = TF.rgb_to_grayscale
sys.modules[module_name] = mod


# ============================================================
# 실제 import 위치 확인
# ============================================================

spec = importlib.util.find_spec("realesrgan")

print("realesrgan spec:", spec)

if spec is not None:
    print("origin:", spec.origin)
    print("locations:", spec.submodule_search_locations)


# ============================================================
# import
# ============================================================

from basicsr.archs.rrdbnet_arch import RRDBNet
print("BasicSR OK")

from realesrgan import RealESRGANer
print("Real-ESRGAN OK")

/content/Real-ESRGAN
Obtaining file:///content/Real-ESRGAN
  error: subprocess-exited-with-error
  
  × python setup.py egg_info did not run successfully.
  │ exit code: 1
  ╰─> See above for output.
  
  note: This error originates from a subprocess, and is likely not a problem with pip.
  Preparing metadata (setup.py) ... error
error: metadata-generation-failed

× Encountered error while generating package metadata.
╰─> See above for output.

note: This is an issue with the package mentioned above, not pip.
hint: See above for details.
realesrgan spec: ModuleSpec(name='realesrgan', loader=<_frozen_importlib_external.SourceFileLoader object at 0x7b459ae48bf0>, origin='/content/Real-ESRGAN/realesrgan/__init__.py', submodule_search_locations=['/content/Real-ESRGAN/realesrgan'])
origin: /content/Real-ESRGAN/realesrgan/__init__.py
locations: ['/content/Real-ESRGAN/realesrgan']
BasicSR OK
Real-ESRGAN OK


In [ ]:
# ============================================================
# Local BasicSR + Local Real-ESRGAN import
# ============================================================

import sys
import types

# 중복 추가 방지
for p in [
    "/content/Real-ESRGAN",
    "/content/BasicSR",
]:
    while p in sys.path:
        sys.path.remove(p)

# 순서 유지
sys.path.insert(0, "/content/BasicSR")
sys.path.insert(0, "/content/Real-ESRGAN")


# torchvision compatibility patch
import torchvision.transforms.functional as TF

module_name = "torchvision.transforms.functional_tensor"

mod = types.ModuleType(module_name)
mod.rgb_to_grayscale = TF.rgb_to_grayscale

sys.modules[module_name] = mod


# BasicSR
from basicsr.archs.rrdbnet_arch import RRDBNet
print("BasicSR OK")


# Real-ESRGAN
from realesrgan import RealESRGANer
print("Real-ESRGAN OK")

BasicSR OK
Real-ESRGAN OK


In [ ]:
import torch
from basicsr.archs.rrdbnet_arch import RRDBNet
from realesrgan import RealESRGANer

%cd /content/Real-ESRGAN

!mkdir -p weights

!wget -O weights/realesrgan-x4plus.pth \
https://github.com/xinntao/Real-ESRGAN/releases/download/v0.1.0/RealESRGAN_x4plus.pth
# ==============================
# 1. RRDBNet 모델 정의
# ==============================

model = RRDBNet(
    num_in_ch=3,
    num_out_ch=3,
    num_feat=64,
    num_block=23,
    num_grow_ch=32,
    scale=4
)

# ==============================
# 2. Real-ESRGAN 로더
# ==============================

upsampler = RealESRGANer(
    scale=4,
    model_path="/content/Real-ESRGAN/weights/realesrgan-x4plus.pth",
    model=model,
    tile=0,
    tile_pad=10,
    pre_pad=0,
    half=torch.cuda.is_available()
)

print("Real-ESRGAN model ready")

/content/Real-ESRGAN
--2026-09-18 16:56:46--  https://github.com/xinntao/Real-ESRGAN/releases/download/v0.1.0/RealESRGAN_x4plus.pth
Resolving github.com (github.com)... 20.205.243.166
Connecting to github.com (github.com)|20.205.243.166|:443... connected.
HTTP request sent, awaiting response... 302 Found
Location: https://release-assets.githubusercontent.com/github-production-release-asset/387326890/08f0e941-ebb7-48f0-9d6a-73e87b710e7e?sp=r&sv=2018-11-09&sr=b&spr=https&se=2026-09-18T17%3A50%3A24Z&rscd=attachment%3B+filename%3DRealESRGAN_x4plus.pth&rsct=application%2Foctet-stream&skoid=96c2d410-5711-43a1-aedd-ab1947aa7ab0&sktid=398a6654-997b-47e9-b12b-9515b896b4de&skt=2026-09-18T16%3A49%3A53Z&ske=2026-09-18T17%3A50%3A24Z&sks=b&skv=2018-11-09&sig=jDdyF%2FeiolwEzH1GPv22%2BEmDNXZDX5IeS2cbDZVCHfI%3D&jwt=eyJ0eXAiOiJKV1QiLCJhbGciOiJIUzI1NiJ9.eyJpc3MiOiJnaXRodWIuY29tIiwiYXVkIjoicmVsZWFzZS1hc3NldHMuZ2l0aHVidXNlcmNvbnRlbnQuY29tIiwia2V5Ijoia2V5MSIsImV4cCI6MTc4OTc1MjQwNiwibmJmIjoxNzg5NzUwNjA2LCJwY

In [ ]:
# ============================================================
# Depth Anything V2 Small - Hugging Face
# 이미지 1장 -> Depth Map
# ============================================================

!pip install -q -U transformers

import torch
import torch.nn.functional as F
import numpy as np
import matplotlib.pyplot as plt

from PIL import Image
from transformers import AutoImageProcessor, AutoModelForDepthEstimation
from google.colab import files


# ============================================================
# 1. Device
# ============================================================

device = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

print("device:", device)


# ============================================================
# 2. Depth Anything V2 Small 로드
# ============================================================

MODEL_ID = "depth-anything/Depth-Anything-V2-Small-hf"

print("Depth Anything V2 Small 로드 중...")

processor = AutoImageProcessor.from_pretrained(MODEL_ID)

model = AutoModelForDepthEstimation.from_pretrained(
    MODEL_ID
).to(device).eval()

print("모델 로드 완료")


   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.3/12.3 MB 93.7 MB/s eta 0:00:00
device: cuda
Depth Anything V2 Small 로드 중...


preprocessor_config.json:   0%|          | 0.00/775 [00:00<?, ?B/s]

config.json:   0%|          | 0.00/950 [00:00<?, ?B/s]

model.safetensors: reconstructing file:   0%|          |  0.00B / 99.2MB            

model.safetensors: downloading bytes:           |  0.00B            

Loading weights:   0%|          | 0/287 [00:00<?, ?it/s]

모델 로드 완료


In [ ]:
from google.colab import drive
drive.mount('/content/drive')

Drive already mounted at /content/drive; to attempt to forcibly remount, call drive.mount("/content/drive", force_remount=True).


In [ ]:
# ============================================================
# IMAGE + VIDEO UNIFIED PIPELINE
#
# 사용법:
#   INPUT_PATH에 이미지 또는 동영상 파일 하나만 지정
#
# 자동 판별:
#   jpg/jpeg/png/... -> IMAGE
#   mp4/mov/avi/...  -> VIDEO
#
# IMAGE:
#   기존 이미지 실험 파이프라인 그대로
#   temporal 없음
#
# VIDEO:
#   동일 core
#   + depth range temporal stabilization
#   + depth temporal
#   + structure temporal
#   + blur temporal
#   + scene cut reset
#   + optical-flow warp
#
# 전제:
#   processor, model, device -> Depth Anything V2 로드 완료
#   upsampler                -> Real-ESRGAN 로드 완료
# ============================================================


import os
import cv2
import torch
import numpy as np
import torch.nn.functional as F

from PIL import Image


# ============================================================
# ★ 0. INPUT / OUTPUT
# ============================================================

# 이미지든 동영상이든 여기에 하나만 넣으면 됨
from google.colab import files
import os

print("처리할 이미지 또는 동영상 파일을 선택하세요.")

uploaded = files.upload()

if len(uploaded) != 1:
    raise ValueError("파일을 1개만 선택해주세요.")

# 사용자가 선택한 파일명 자동 획득
INPUT_PATH = next(iter(uploaded.keys()))

SAVE_PATH = "/content/drive/MyDrive/KSY/capstone/results"


# ============================================================
# ★ 1. IMAGE 기본 파라미터
# ============================================================

# IMAGE 실험에서 원본을 LR로 만들어 테스트할지 여부
# VIDEO에는 적용하지 않음
MAKE_LOW_RESOLUTION = True

DOWNSCALE = 8
UPSCALE = 4


# ------------------------------------------------------------
# Depth
#
# 0 = Far
# 1 = Near
# ------------------------------------------------------------

DEPTH_FAR = 0.10
DEPTH_NEAR = 0.30


# ------------------------------------------------------------
# Structure
# ------------------------------------------------------------

EDGE_WEIGHT = 0.4
RESIDUAL_WEIGHT = 0.6

RESIDUAL_PERCENTILE = 80

STRUCTURE_START = 0.15
STRUCTURE_PROTECT_POWER = 0.4


# ------------------------------------------------------------
# Blur
# ------------------------------------------------------------

MIN_STRUCTURE_BLUR = 0.03

BLUR_SIGMA = 2.5

MASK_SIGMA = 0.5


# ============================================================
# ★ 2. VIDEO 전용 파라미터
#
# IMAGE에는 적용되지 않음
# ============================================================

VIDEO_DEPTH_RANGE_ALPHA = 0.95

VIDEO_DEPTH_ALPHA = 0.80

VIDEO_STRUCTURE_ALPHA = 0.70

VIDEO_BLUR_ALPHA = 0.80


# Scene Cut
SCENE_CUT_THRESHOLD = 0.30


# Optical Flow
USE_OPTICAL_FLOW = True


# Debug video 저장
SAVE_DEBUG_VIDEO = True


# ============================================================
# 3. 지원 확장자
# ============================================================

IMAGE_EXTENSIONS = {
    ".jpg",
    ".jpeg",
    ".png",
    ".webp",
    ".bmp",
    ".tif",
    ".tiff",
}


VIDEO_EXTENSIONS = {
    ".mp4",
    ".mov",
    ".avi",
    ".mkv",
    ".webm",
    ".m4v",
}


# ============================================================
# 4. 입력 파일 확인
# ============================================================

if not os.path.exists(INPUT_PATH):

    raise FileNotFoundError(
        f"입력 파일을 찾을 수 없습니다: {INPUT_PATH}"
    )


input_ext = os.path.splitext(
    INPUT_PATH
)[1].lower()


print()
print("======================================")
print("INPUT FILE CHECK")
print("Path      :", INPUT_PATH)
print("Extension :", input_ext)
print("======================================")


# ============================================================
# 5. VIDEO TEMPORAL STATE
# ============================================================

class TemporalState:

    def __init__(self):

        self.prev_frame = None

        self.prev_depth = None

        self.prev_structure = None

        self.prev_blur = None

        self.depth_low = None

        self.depth_high = None


    def reset(self):

        self.prev_frame = None

        self.prev_depth = None

        self.prev_structure = None

        self.prev_blur = None

        self.depth_low = None

        self.depth_high = None


# ============================================================
# 6. Edge Structure
#
# 기존 IMAGE 코드 그대로
# ============================================================

def make_edge_structure_map(
    img,
    blur_sigma=1.5
):

    gray = cv2.cvtColor(
        img,
        cv2.COLOR_BGR2GRAY
    ).astype(np.float32)


    gx = cv2.Sobel(
        gray,
        cv2.CV_32F,
        1,
        0,
        ksize=3
    )


    gy = cv2.Sobel(
        gray,
        cv2.CV_32F,
        0,
        1,
        ksize=3
    )


    mag = np.sqrt(
        gx ** 2
        +
        gy ** 2
    )


    norm = (
        np.percentile(
            mag,
            99
        )
        +
        1e-8
    )


    mag = np.clip(
        mag / norm,
        0.0,
        1.0
    )


    if blur_sigma > 0:

        mag = cv2.GaussianBlur(
            mag,
            (0, 0),
            blur_sigma
        )


    return np.clip(
        mag,
        0.0,
        1.0
    ).astype(np.float32)


# ============================================================
# 7. Residual Structure
#
# 기존 IMAGE 코드 그대로
# ============================================================

def make_residual_structure_map(
    I_up,
    I_sr,
    percentile=80,
    blur_sigma=2.0
):

    diff = np.abs(
        I_sr.astype(np.float32)
        -
        I_up.astype(np.float32)
    )


    diff = np.mean(
        diff,
        axis=2
    )


    threshold = np.percentile(
        diff,
        percentile
    )


    high = np.percentile(
        diff,
        99
    )


    residual = (
        diff - threshold
    ) / (
        high - threshold + 1e-8
    )


    residual = np.clip(
        residual,
        0.0,
        1.0
    )


    if blur_sigma > 0:

        residual = cv2.GaussianBlur(
            residual,
            (0, 0),
            blur_sigma
        )


    return np.clip(
        residual,
        0.0,
        1.0
    ).astype(np.float32)


# ============================================================
# 8. Depth Anything RAW Depth
# ============================================================

@torch.no_grad()
def estimate_raw_depth(
    img_bgr
):

    h, w = img_bgr.shape[:2]


    depth_image = Image.fromarray(
        cv2.cvtColor(
            img_bgr,
            cv2.COLOR_BGR2RGB
        )
    )


    inputs = processor(
        images=depth_image,
        return_tensors="pt"
    )


    inputs = {
        k: v.to(device)
        for k, v in inputs.items()
    }


    outputs = model(
        **inputs
    )


    predicted_depth = (
        outputs.predicted_depth
    )


    depth = F.interpolate(
        predicted_depth.unsqueeze(1),
        size=(h, w),
        mode="bicubic",
        align_corners=False
    ).squeeze()


    depth = (
        depth
        .detach()
        .cpu()
        .numpy()
        .astype(np.float32)
    )


    return depth


# ============================================================
# 9. IMAGE Depth Normalization
#
# 기존 IMAGE 방식 그대로
#
# 각 이미지 자체의 percentile 2 ~ 98
# ============================================================

def normalize_depth_image(
    depth
):

    low = np.percentile(
        depth,
        2
    )


    high = np.percentile(
        depth,
        98
    )


    depth_normalized = (
        (depth - low)
        /
        (high - low + 1e-8)
    )


    depth_normalized = np.clip(
        depth_normalized,
        0.0,
        1.0
    )


    return depth_normalized


# ============================================================
# 10. VIDEO Depth Normalization
#
# VIDEO에서만 percentile range temporal smoothing
# ============================================================

def normalize_depth_video(
    depth,
    state
):

    current_low = np.percentile(
        depth,
        2
    )


    current_high = np.percentile(
        depth,
        98
    )


    if state.depth_low is None:

        state.depth_low = current_low

        state.depth_high = current_high

    else:

        state.depth_low = (
            VIDEO_DEPTH_RANGE_ALPHA
            *
            state.depth_low
            +
            (1.0 - VIDEO_DEPTH_RANGE_ALPHA)
            *
            current_low
        )


        state.depth_high = (
            VIDEO_DEPTH_RANGE_ALPHA
            *
            state.depth_high
            +
            (1.0 - VIDEO_DEPTH_RANGE_ALPHA)
            *
            current_high
        )


    depth_normalized = (
        (depth - state.depth_low)
        /
        (
            state.depth_high
            -
            state.depth_low
            +
            1e-8
        )
    )


    depth_normalized = np.clip(
        depth_normalized,
        0.0,
        1.0
    )


    return depth_normalized


# ============================================================
# 11. Scene Cut Detection
#
# VIDEO ONLY
# ============================================================

def detect_scene_cut(
    prev_frame,
    current_frame
):

    if prev_frame is None:

        return False


    prev_small = cv2.resize(
        prev_frame,
        (64, 64),
        interpolation=cv2.INTER_AREA
    )


    curr_small = cv2.resize(
        current_frame,
        (64, 64),
        interpolation=cv2.INTER_AREA
    )


    prev_hsv = cv2.cvtColor(
        prev_small,
        cv2.COLOR_BGR2HSV
    )


    curr_hsv = cv2.cvtColor(
        curr_small,
        cv2.COLOR_BGR2HSV
    )


    hist_prev = cv2.calcHist(
        [prev_hsv],
        [0, 1],
        None,
        [32, 32],
        [0, 180, 0, 256]
    )


    hist_curr = cv2.calcHist(
        [curr_hsv],
        [0, 1],
        None,
        [32, 32],
        [0, 180, 0, 256]
    )


    cv2.normalize(
        hist_prev,
        hist_prev
    )


    cv2.normalize(
        hist_curr,
        hist_curr
    )


    distance = cv2.compareHist(
        hist_prev,
        hist_curr,
        cv2.HISTCMP_BHATTACHARYYA
    )


    return (
        distance
        >
        SCENE_CUT_THRESHOLD
    )


# ============================================================
# 12. Optical Flow
#
# current -> previous 방향
#
# VIDEO ONLY
# ============================================================

def calculate_backward_flow(
    prev_frame,
    current_frame,
    out_size
):

    out_w, out_h = out_size


    prev_gray = cv2.cvtColor(
        prev_frame,
        cv2.COLOR_BGR2GRAY
    )


    curr_gray = cv2.cvtColor(
        current_frame,
        cv2.COLOR_BGR2GRAY
    )


    flow = cv2.calcOpticalFlowFarneback(
        curr_gray,
        prev_gray,
        None,
        0.5,
        3,
        15,
        3,
        5,
        1.2,
        0
    )


    flow = cv2.resize(
        flow,
        (out_w, out_h),
        interpolation=cv2.INTER_LINEAR
    )


    scale_x = (
        out_w
        /
        prev_frame.shape[1]
    )


    scale_y = (
        out_h
        /
        prev_frame.shape[0]
    )


    flow[..., 0] *= scale_x

    flow[..., 1] *= scale_y


    return flow


# ============================================================
# 13. Previous Map -> Current Frame Warp
#
# VIDEO ONLY
# ============================================================

def warp_previous_map(
    previous_map,
    flow
):

    h, w = previous_map.shape[:2]


    grid_x, grid_y = np.meshgrid(
        np.arange(
            w,
            dtype=np.float32
        ),
        np.arange(
            h,
            dtype=np.float32
        )
    )


    map_x = (
        grid_x
        +
        flow[..., 0]
    )


    map_y = (
        grid_y
        +
        flow[..., 1]
    )


    warped = cv2.remap(
        previous_map.astype(np.float32),
        map_x.astype(np.float32),
        map_y.astype(np.float32),
        interpolation=cv2.INTER_LINEAR,
        borderMode=cv2.BORDER_REPLICATE
    )


    return warped


# ============================================================
# 14. Temporal Blend
#
# VIDEO ONLY
#
# alpha 높음
# -> 이전 warped map 비중 높음
# ============================================================

def temporal_blend(
    current,
    previous,
    alpha
):

    if previous is None:

        return current.copy()


    return (
        alpha
        *
        previous
        +
        (1.0 - alpha)
        *
        current
    )


# ============================================================
# 15. 공통 CORE
#
# IMAGE:
#   process_core(frame, state=None)
#
# VIDEO:
#   process_core(frame, state=TemporalState)
#
# 따라서 IMAGE 계산에는 temporal이 들어가지 않음
# ============================================================

def process_core(
    img_bgr,
    state=None
):

    h, w = img_bgr.shape[:2]


    out_w = (
        w
        *
        UPSCALE
    )


    out_h = (
        h
        *
        UPSCALE
    )


    # ========================================================
    # VIDEO ONLY
    # Scene Cut
    # ========================================================

    if state is not None:

        is_scene_cut = detect_scene_cut(
            state.prev_frame,
            img_bgr
        )


        if is_scene_cut:

            print(
                "\nScene cut detected -> temporal reset"
            )

            state.reset()


    # ========================================================
    # Lanczos
    #
    # 구조 계산/비교용
    # ========================================================

    I_up = cv2.resize(
        img_bgr,
        (out_w, out_h),
        interpolation=cv2.INTER_LANCZOS4
    )


    # ========================================================
    # Real-ESRGAN
    #
    # 최종 화질 baseline
    # ========================================================

    with torch.no_grad():

        I_sr, _ = upsampler.enhance(
            img_bgr,
            outscale=UPSCALE
        )


    if I_sr.shape[:2] != (
        out_h,
        out_w
    ):

        I_sr = cv2.resize(
            I_sr,
            (out_w, out_h),
            interpolation=cv2.INTER_CUBIC
        )


    # ========================================================
    # RAW Depth
    # ========================================================

    raw_depth = estimate_raw_depth(
        img_bgr
    )


    # ========================================================
    # Depth Normalization
    #
    # IMAGE = 기존 방식
    # VIDEO = temporal range
    # ========================================================

    if state is None:

        depth_normalized = (
            normalize_depth_image(
                raw_depth
            )
        )

    else:

        depth_normalized = (
            normalize_depth_video(
                raw_depth,
                state
            )
        )


    # ========================================================
    # M_depth
    # ========================================================

    M_depth_2d = cv2.resize(
        depth_normalized,
        (out_w, out_h),
        interpolation=cv2.INTER_CUBIC
    )


    M_depth_2d = cv2.GaussianBlur(
        M_depth_2d,
        (0, 0),
        sigmaX=2.0
    )


    M_depth_2d = np.clip(
        M_depth_2d,
        0.0,
        1.0
    ).astype(np.float32)


    # ========================================================
    # Structure
    # ========================================================

    M_edge = (
        make_edge_structure_map(
            I_up
        )
    )


    M_residual = (
        make_residual_structure_map(
            I_up,
            I_sr,
            percentile=RESIDUAL_PERCENTILE
        )
    )


    M_structure_2d = np.clip(
        EDGE_WEIGHT
        *
        M_edge
        +
        RESIDUAL_WEIGHT
        *
        M_residual,
        0.0,
        1.0
    ).astype(np.float32)


    # ========================================================
    # VIDEO ONLY
    #
    # Optical Flow
    # + Temporal Depth
    # + Temporal Structure
    # ========================================================

    if state is not None:

        warped_depth = None

        warped_structure = None

        warped_blur = None


        if (
            state.prev_frame is not None
            and
            USE_OPTICAL_FLOW
        ):

            flow = calculate_backward_flow(
                state.prev_frame,
                img_bgr,
                (out_w, out_h)
            )


            if state.prev_depth is not None:

                warped_depth = warp_previous_map(
                    state.prev_depth,
                    flow
                )


            if state.prev_structure is not None:

                warped_structure = warp_previous_map(
                    state.prev_structure,
                    flow
                )


            if state.prev_blur is not None:

                warped_blur = warp_previous_map(
                    state.prev_blur,
                    flow
                )


        else:

            warped_depth = (
                state.prev_depth
            )

            warped_structure = (
                state.prev_structure
            )

            warped_blur = (
                state.prev_blur
            )


        # ----------------------------------------------------
        # Depth Temporal
        # ----------------------------------------------------

        M_depth_2d = temporal_blend(
            M_depth_2d,
            warped_depth,
            VIDEO_DEPTH_ALPHA
        )


        M_depth_2d = np.clip(
            M_depth_2d,
            0.0,
            1.0
        )


        # ----------------------------------------------------
        # Structure Temporal
        # ----------------------------------------------------

        M_structure_2d = temporal_blend(
            M_structure_2d,
            warped_structure,
            VIDEO_STRUCTURE_ALPHA
        )


        M_structure_2d = np.clip(
            M_structure_2d,
            0.0,
            1.0
        )


    else:

        warped_blur = None


    # ========================================================
    # 여기부터 IMAGE 기존 계산
    # ========================================================

    D = M_depth_2d

    S = M_structure_2d


    # ========================================================
    # Depth -> Far Strength
    # ========================================================

    far_strength = 1.0 - np.clip(
        (
            D
            -
            DEPTH_FAR
        )
        /
        (
            DEPTH_NEAR
            -
            DEPTH_FAR
            +
            1e-8
        ),
        0.0,
        1.0
    )


    # Smoothstep
    far_strength = (
        far_strength ** 2
        *
        (
            3.0
            -
            2.0
            *
            far_strength
        )
    )


    # ========================================================
    # Structure Protection
    # ========================================================

    structure_protect = np.clip(
        (
            S
            -
            STRUCTURE_START
        )
        /
        (
            1.0
            -
            STRUCTURE_START
            +
            1e-8
        ),
        0.0,
        1.0
    )


    structure_protect = (
        structure_protect
        **
        STRUCTURE_PROTECT_POWER
    )


    # ========================================================
    # Current Blur Strength
    #
    # Far + No Structure
    # -> blur 강함
    #
    # Far + Structure
    # -> blur 억제
    #
    # Near
    # -> blur 거의 없음
    # ========================================================

    blur_current = (
        far_strength
        *
        (
            1.0
            -
            (
                1.0
                -
                MIN_STRUCTURE_BLUR
            )
            *
            structure_protect
        )
    )


    if MASK_SIGMA > 0:

        blur_current = cv2.GaussianBlur(
            blur_current,
            (0, 0),
            sigmaX=MASK_SIGMA
        )


    blur_current = np.clip(
        blur_current,
        0.0,
        1.0
    )


    # ========================================================
    # VIDEO ONLY
    # Blur Temporal
    # ========================================================

    if state is not None:

        blur_strength = temporal_blend(
            blur_current,
            warped_blur,
            VIDEO_BLUR_ALPHA
        )


        blur_strength = np.clip(
            blur_strength,
            0.0,
            1.0
        )


    else:

        # IMAGE는 기존 blur map 그대로
        blur_strength = (
            blur_current
        )


    # ========================================================
    # Real-ESRGAN Blur
    # ========================================================

    I_sr_f = I_sr.astype(
        np.float32
    )


    I_blur = cv2.GaussianBlur(
        I_sr_f,
        (0, 0),
        sigmaX=BLUR_SIGMA,
        sigmaY=BLUR_SIGMA
    )


    # ========================================================
    # Final Proposed
    #
    # Real-ESRGAN ↔ Blurred Real-ESRGAN
    #
    # Lanczos는 최종 합성에 사용하지 않음
    # ========================================================

    A = blur_strength[
        ...,
        None
    ]


    I_final = (
        (1.0 - A)
        *
        I_sr_f
        +
        A
        *
        I_blur
    )


    I_final = np.clip(
        I_final,
        0,
        255
    ).astype(np.uint8)


    # ========================================================
    # Difference
    # ========================================================

    diff_sr_final = np.mean(
        np.abs(
            I_sr.astype(np.float32)
            -
            I_final.astype(np.float32)
        ),
        axis=2
    )


    # ========================================================
    # VIDEO State Update
    # ========================================================

    if state is not None:

        state.prev_frame = (
            img_bgr.copy()
        )


        state.prev_depth = (
            M_depth_2d.copy()
        )


        state.prev_structure = (
            M_structure_2d.copy()
        )


        state.prev_blur = (
            blur_strength.copy()
        )


    # ========================================================
    # Return
    # ========================================================

    return {

        "input":
            img_bgr,

        "lanczos":
            I_up,

        "esrgan":
            I_sr,

        "depth":
            M_depth_2d,

        "edge":
            M_edge,

        "residual":
            M_residual,

        "structure":
            M_structure_2d,

        "far":
            far_strength,

        "structure_protect":
            structure_protect,

        "blur":
            blur_strength,

        "esrgan_blurred":
            np.clip(
                I_blur,
                0,
                255
            ).astype(np.uint8),

        "final":
            I_final,

        "difference":
            diff_sr_final,
    }


# ============================================================
# 16. Float Map 저장 Helper
# ============================================================

def save_float_map(
    path,
    array
):

    array = np.clip(
        array,
        0.0,
        1.0
    )


    cv2.imwrite(
        path,
        (
            array * 255
        ).astype(np.uint8)
    )


# ============================================================
# 17. IMAGE PROCESS
#
# ★ temporal 없음
# ★ 기존 이미지 실험 방식
# ============================================================

def process_image(
    image_path,
    save_path
):

    image_name = os.path.splitext(
        os.path.basename(
            image_path
        )
    )[0]


    experiment_dir = os.path.join(
        save_path,
        image_name
    )


    os.makedirs(
        experiment_dir,
        exist_ok=True
    )


    # --------------------------------------------------------
    # Original Load
    # --------------------------------------------------------

    hr_img = cv2.imread(
        image_path
    )


    if hr_img is None:

        raise FileNotFoundError(
            f"이미지를 읽을 수 없습니다: {image_path}"
        )


    hr_h, hr_w = (
        hr_img.shape[:2]
    )


    # --------------------------------------------------------
    # 기존 IMAGE LR 생성 방식
    # --------------------------------------------------------

    if MAKE_LOW_RESOLUTION:

        lr_w = max(
            1,
            hr_w // DOWNSCALE
        )


        lr_h = max(
            1,
            hr_h // DOWNSCALE
        )


        img_bgr = cv2.resize(
            hr_img,
            (lr_w, lr_h),
            interpolation=cv2.INTER_AREA
        )


    else:

        img_bgr = (
            hr_img.copy()
        )


    h, w = (
        img_bgr.shape[:2]
    )


    print()
    print("======================================")
    print("AUTO DETECTED : IMAGE")
    print("Input         :", image_path)
    print("Original      :", (hr_w, hr_h))
    print("LR            :", (w, h))
    print(
        "SR output     :",
        (
            w * UPSCALE,
            h * UPSCALE
        )
    )
    print("Temporal      : OFF")
    print("======================================")


    # --------------------------------------------------------
    # ★ IMAGE = state=None
    # --------------------------------------------------------

    result = process_core(
        img_bgr,
        state=None
    )


    # --------------------------------------------------------
    # Save
    # --------------------------------------------------------

    cv2.imwrite(
        os.path.join(
            experiment_dir,
            "00_original.png"
        ),
        hr_img
    )


    cv2.imwrite(
        os.path.join(
            experiment_dir,
            "01_lr_input.png"
        ),
        result["input"]
    )


    cv2.imwrite(
        os.path.join(
            experiment_dir,
            "02_lanczos.png"
        ),
        result["lanczos"]
    )


    cv2.imwrite(
        os.path.join(
            experiment_dir,
            "03_realesrgan.png"
        ),
        result["esrgan"]
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "04_depth_gray.png"
        ),
        result["depth"]
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "06_edge_map.png"
        ),
        result["edge"]
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "07_residual_map.png"
        ),
        result["residual"]
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "08_structure_map.png"
        ),
        result["structure"]
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "09_far_strength.png"
        ),
        result["far"]
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "10_structure_protection.png"
        ),
        result["structure_protect"]
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "11_blur_weight.png"
        ),
        result["blur"]
    )


    cv2.imwrite(
        os.path.join(
            experiment_dir,
            "12_realesrgan_blurred.png"
        ),
        result["esrgan_blurred"]
    )


    cv2.imwrite(
        os.path.join(
            experiment_dir,
            "13_proposed.png"
        ),
        result["final"]
    )


    # --------------------------------------------------------
    # Raw Difference
    # --------------------------------------------------------

    np.save(
        os.path.join(
            experiment_dir,
            "14_difference_raw.npy"
        ),
        result["difference"]
    )


    diff_max = np.percentile(
        result["difference"],
        99
    )


    diff_vis = np.clip(
        result["difference"]
        /
        (
            diff_max
            +
            1e-8
        ),
        0.0,
        1.0
    )


    save_float_map(
        os.path.join(
            experiment_dir,
            "15_difference_gray.png"
        ),
        diff_vis
    )


    # --------------------------------------------------------
    # Statistics
    # --------------------------------------------------------

    D = result["depth"]

    S = result["structure"]

    far_strength = (
        result["far"]
    )

    structure_protect = (
        result["structure_protect"]
    )

    blur_strength = (
        result["blur"]
    )


    far_region = (
        far_strength >= 0.5
    )


    structured_region = (
        structure_protect >= 0.5
    )


    far_structured = (
        far_region
        &
        structured_region
    )


    far_nonstructured = (
        far_region
        &
        (~structured_region)
    )


    stats = [

        "TYPE=IMAGE",

        f"IMAGE_PATH={image_path}",

        f"ORIGINAL_SIZE={hr_w}x{hr_h}",

        f"LR_SIZE={w}x{h}",

        f"SR_SIZE="
        f"{w * UPSCALE}x"
        f"{h * UPSCALE}",

        f"DEPTH_FAR={DEPTH_FAR}",

        f"DEPTH_NEAR={DEPTH_NEAR}",

        f"STRUCTURE_START="
        f"{STRUCTURE_START}",

        f"STRUCTURE_PROTECT_POWER="
        f"{STRUCTURE_PROTECT_POWER}",

        f"MIN_STRUCTURE_BLUR="
        f"{MIN_STRUCTURE_BLUR}",

        f"BLUR_SIGMA="
        f"{BLUR_SIGMA}",

        f"MASK_SIGMA="
        f"{MASK_SIGMA}",

        f"depth_mean="
        f"{D.mean():.6f}",

        f"structure_mean="
        f"{S.mean():.6f}",

        f"far_strength_mean="
        f"{far_strength.mean():.6f}",

        f"blur_weight_mean="
        f"{blur_strength.mean():.6f}",

        f"difference_mean="
        f"{result['difference'].mean():.6f}",
    ]


    if np.any(
        far_structured
    ):

        stats.append(
            "far_structure_blur_mean="
            f"{blur_strength[far_structured].mean():.6f}"
        )


    if np.any(
        far_nonstructured
    ):

        stats.append(
            "far_no_structure_blur_mean="
            f"{blur_strength[far_nonstructured].mean():.6f}"
        )


    stats_text = "\n".join(
        stats
    )


    with open(
        os.path.join(
            experiment_dir,
            "19_parameters_and_stats.txt"
        ),
        "w"
    ) as f:

        f.write(
            stats_text
        )


    final_path = os.path.join(
        experiment_dir,
        "13_proposed.png"
    )


    print()
    print("IMAGE COMPLETE")
    print("Final :", final_path)
    print("Saved :", experiment_dir)


    return (
        final_path,
        experiment_dir
    )


# ============================================================
# 18. VIDEO Writer Helper
# ============================================================

# ============================================================
# 18. VIDEO Writer Helper
# ============================================================

def create_writer(
    path,
    fps,
    size
):

    fourcc = cv2.VideoWriter_fourcc(
        *"mp4v"
    )

    writer = cv2.VideoWriter(
        path,
        fourcc,
        fps,
        size
    )

    if not writer.isOpened():

        raise RuntimeError(
            f"VideoWriter 생성 실패: {path}"
        )

    return writer


# ============================================================
# 19. VIDEO PROCESS
#
# IMAGE와 동일하게:
#
# Original Video
#       ↓
# DOWNSCALE
#       ↓
# LR Video
#       ↓
# process_core()
#       ↓
# Real-ESRGAN × UPSCALE
# + Depth
# + Structure
# + Blur
# + Temporal
#       ↓
# Final Video
# ============================================================

def process_video(
    video_path,
    save_path
):

    # ========================================================
    # 이름 / 저장 폴더
    # ========================================================

    video_name = os.path.splitext(
        os.path.basename(
            video_path
        )
    )[0]

    experiment_dir = os.path.join(
        save_path,
        video_name
    )

    os.makedirs(
        experiment_dir,
        exist_ok=True
    )


    # ========================================================
    # Video Open
    # ========================================================

    cap = cv2.VideoCapture(
        video_path
    )

    if not cap.isOpened():

        raise RuntimeError(
            f"동영상을 열 수 없습니다: {video_path}"
        )


    # ========================================================
    # Video Information
    # ========================================================

    fps = cap.get(
        cv2.CAP_PROP_FPS
    )

    if (
        not np.isfinite(fps)
        or
        fps <= 0
    ):

        fps = 30.0


    frame_count = int(
        cap.get(
            cv2.CAP_PROP_FRAME_COUNT
        )
    )


    input_w = int(
        cap.get(
            cv2.CAP_PROP_FRAME_WIDTH
        )
    )

    input_h = int(
        cap.get(
            cv2.CAP_PROP_FRAME_HEIGHT
        )
    )


    # ========================================================
    # ★ VIDEO LR SIZE
    #
    # IMAGE와 동일하게 원본을 먼저 저해상도로 만듦
    # ========================================================

    if MAKE_LOW_RESOLUTION:

        lr_w = max(
            1,
            input_w // DOWNSCALE
        )

        lr_h = max(
            1,
            input_h // DOWNSCALE
        )

    else:

        lr_w = input_w
        lr_h = input_h


    # ========================================================
    # ★ Final SR Size
    #
    # process_core에서 LR → UPSCALE
    # ========================================================

    out_w = (
        lr_w
        *
        UPSCALE
    )

    out_h = (
        lr_h
        *
        UPSCALE
    )


    # ========================================================
    # Information
    # ========================================================

    print()
    print("======================================")
    print("AUTO DETECTED : VIDEO")
    print("Input         :", video_path)

    print(
        "Original size :",
        (input_w, input_h)
    )

    print(
        "LR size       :",
        (lr_w, lr_h)
    )

    print(
        "SR output     :",
        (out_w, out_h)
    )

    print(
        "DOWNSCALE     :",
        DOWNSCALE
    )

    print(
        "UPSCALE       :",
        UPSCALE
    )

    print(
        "FPS           :",
        fps
    )

    print(
        "Frames        :",
        frame_count
    )

    print(
        "Temporal      : ON"
    )

    print(
        "Optical Flow  :",
        USE_OPTICAL_FLOW
    )

    print("======================================")


    # ========================================================
    # ★ 1. LR VIDEO PREVIEW
    #
    # 실제 알고리즘에 들어가는 LR 영상 저장
    # ========================================================

    lr_video_path = os.path.join(
        experiment_dir,
        "00_low_resolution_video.mp4"
    )

    writer_lr = create_writer(
        lr_video_path,
        fps,
        (lr_w, lr_h)
    )


    print()
    print("======================================")
    print("CREATING LOW RESOLUTION VIDEO")
    print(
        "Original :",
        (input_w, input_h)
    )
    print(
        "LR       :",
        (lr_w, lr_h)
    )
    print("======================================")


    cap.set(
        cv2.CAP_PROP_POS_FRAMES,
        0
    )

    lr_frame_idx = 0


    while True:

        ret, frame = cap.read()

        if not ret:

            break


        # ----------------------------------------------------
        # Original → LR
        # ----------------------------------------------------

        if MAKE_LOW_RESOLUTION:

            frame_lr = cv2.resize(
                frame,
                (lr_w, lr_h),
                interpolation=cv2.INTER_AREA
            )

        else:

            frame_lr = frame.copy()


        writer_lr.write(
            frame_lr
        )


        lr_frame_idx += 1


        if frame_count > 0:

            print(
                f"\rCreating LR "
                f"{lr_frame_idx}/"
                f"{frame_count}",
                end=""
            )

        else:

            print(
                f"\rCreating LR "
                f"{lr_frame_idx}",
                end=""
            )


    writer_lr.release()


    print()
    print()
    print(
        "LR VIDEO SAVED:",
        lr_video_path
    )


    # ========================================================
    # ★ 본 처리를 위해 첫 프레임으로 되돌림
    # ========================================================

    cap.set(
        cv2.CAP_PROP_POS_FRAMES,
        0
    )


    # ========================================================
    # 2. Main Final Video
    # ========================================================

    final_path = os.path.join(
        experiment_dir,
        "final.mp4"
    )

    writer_final = create_writer(
        final_path,
        fps,
        (out_w, out_h)
    )


    # ========================================================
    # 3. Real-ESRGAN Only Video
    # ========================================================

    esrgan_path = os.path.join(
        experiment_dir,
        "realesrgan.mp4"
    )

    writer_esrgan = create_writer(
        esrgan_path,
        fps,
        (out_w, out_h)
    )


    # ========================================================
    # 4. Debug Videos
    # ========================================================

    debug_writers = {}


    if SAVE_DEBUG_VIDEO:

        debug_keys = [

            "depth",

            "structure",

            "far",

            "structure_protect",

            "blur",

        ]


        for key in debug_keys:

            debug_path = os.path.join(
                experiment_dir,
                f"{key}.mp4"
            )

            debug_writers[key] = (
                create_writer(
                    debug_path,
                    fps,
                    (out_w, out_h)
                )
            )


    # ========================================================
    # ★ VIDEO마다 독립 Temporal State
    # ========================================================

    state = TemporalState()


    frame_idx = 0


    # ========================================================
    # 5. Main Frame Loop
    # ========================================================

    print()
    print("======================================")
    print("START VIDEO PROCESSING")
    print("======================================")


    try:

        while True:

            # =================================================
            # Original Frame Read
            # =================================================

            ret, frame = cap.read()


            if not ret:

                break


            # =================================================
            # ★ Original → LR
            #
            # 여기서 실제 입력 영상의 해상도를 낮춤
            # =================================================

            if MAKE_LOW_RESOLUTION:

                frame_lr = cv2.resize(
                    frame,
                    (lr_w, lr_h),
                    interpolation=cv2.INTER_AREA
                )

            else:

                frame_lr = (
                    frame.copy()
                )


            # =================================================
            # ★ 동일 process_core
            #
            # IMAGE:
            # process_core(img, state=None)
            #
            # VIDEO:
            # process_core(frame_lr, state=state)
            #
            # 즉 VIDEO만 Temporal 추가
            # =================================================

            result = process_core(
                frame_lr,
                state=state
            )


            # =================================================
            # Final Proposed
            # =================================================

            writer_final.write(
                result["final"]
            )


            # =================================================
            # Real-ESRGAN Only
            # =================================================

            writer_esrgan.write(
                result["esrgan"]
            )


            # =================================================
            # Debug Videos
            # =================================================

            if SAVE_DEBUG_VIDEO:

                for key, writer in (
                    debug_writers.items()
                ):

                    m = np.clip(
                        result[key],
                        0.0,
                        1.0
                    )


                    m8 = (
                        m
                        *
                        255
                    ).astype(
                        np.uint8
                    )


                    m_bgr = cv2.cvtColor(
                        m8,
                        cv2.COLOR_GRAY2BGR
                    )


                    writer.write(
                        m_bgr
                    )


            # =================================================
            # Progress
            # =================================================

            frame_idx += 1


            if frame_count > 0:

                print(
                    f"\rProcessing "
                    f"{frame_idx}/"
                    f"{frame_count}",
                    end=""
                )

            else:

                print(
                    f"\rProcessing "
                    f"{frame_idx}",
                    end=""
                )


    # ========================================================
    # 반드시 Release
    # ========================================================

    finally:

        cap.release()

        writer_final.release()

        writer_esrgan.release()


        for writer in (
            debug_writers.values()
        ):

            writer.release()


    # ========================================================
    # Complete
    # ========================================================

    print()
    print()
    print("======================================")
    print("VIDEO COMPLETE")
    print("======================================")

    print(
        "Original size :",
        f"{input_w}x{input_h}"
    )

    print(
        "LR size       :",
        f"{lr_w}x{lr_h}"
    )

    print(
        "SR size       :",
        f"{out_w}x{out_h}"
    )

    print(
        "LR Video      :",
        lr_video_path
    )

    print(
        "Real-ESRGAN   :",
        esrgan_path
    )

    print(
        "Final         :",
        final_path
    )

    print(
        "Saved         :",
        experiment_dir
    )

    print("======================================")


    return (
        final_path,
        experiment_dir
    )

# ============================================================
# 20. ★ IMAGE / VIDEO 자동 판별
#
# 사용자가 MODE 선택할 필요 없음
#
# INPUT_PATH의 확장자를 보고 자동 결정
# ============================================================

def process_media(
    input_path,
    save_path
):

    ext = os.path.splitext(
        input_path
    )[1].lower()


    print()
    print("======================================")
    print("AUTO MEDIA DETECTION")
    print("Input     :", input_path)
    print("Extension :", ext)


    # ========================================================
    # IMAGE
    # ========================================================

    if ext in IMAGE_EXTENSIONS:

        print("Detected  : IMAGE")
        print("======================================")

        return process_image(
            input_path,
            save_path
        )


    # ========================================================
    # VIDEO
    # ========================================================

    elif ext in VIDEO_EXTENSIONS:

        print("Detected  : VIDEO")
        print("======================================")

        return process_video(
            input_path,
            save_path
        )


    # ========================================================
    # Unsupported
    # ========================================================

    else:

        print("Detected  : UNKNOWN")
        print("======================================")

        raise ValueError(
            "지원하지 않는 파일 형식입니다.\n"
            f"입력 확장자: {ext}\n"
            f"지원 IMAGE: {sorted(IMAGE_EXTENSIONS)}\n"
            f"지원 VIDEO: {sorted(VIDEO_EXTENSIONS)}"
        )


# ============================================================
# 21. RUN
#
# ★ 사용자는 INPUT_PATH만 변경하면 됨
# ============================================================

result_path, experiment_dir = process_media(
    INPUT_PATH,
    SAVE_PATH
)


print()
print("======================================")
print("ALL DONE")
print("Input :", INPUT_PATH)
print("Result:", result_path)
print("Saved :", experiment_dir)
print("======================================")

처리할 이미지 또는 동영상 파일을 선택하세요.


Saving vid.mp4 to vid.mp4

INPUT FILE CHECK
Path      : vid.mp4
Extension : .mp4

AUTO MEDIA DETECTION
Input     : vid.mp4
Extension : .mp4
Detected  : VIDEO

AUTO DETECTED : VIDEO
Input         : vid.mp4
Original size : (1920, 1080)
LR size       : (240, 135)
SR output     : (960, 540)
DOWNSCALE     : 8
UPSCALE       : 4
FPS           : 30.0
Frames        : 348
Temporal      : ON
Optical Flow  : True

CREATING LOW RESOLUTION VIDEO
Original : (1920, 1080)
LR       : (240, 135)
Creating LR 348/348

LR VIDEO SAVED: /content/drive/MyDrive/KSY/capstone/results/vid/00_low_resolution_video.mp4

START VIDEO PROCESSING
Processing 79/348
Scene cut detected -> temporal reset
Processing 136/348
Scene cut detected -> temporal reset
Processing 188/348
Scene cut detected -> temporal reset
Processing 296/348
Scene cut detected -> temporal reset
Processing 348/348

VIDEO COMPLETE
Original size : 1920x1080
LR size       : 240x135
SR size       : 960x540
LR Video      : /content/drive/MyDrive/KSY/capsto

In [ ]:
import cv2
import os

paths = {
    "LR": os.path.join(
        experiment_dir,
        "00_low_resolution_video.mp4"
    ),
    "Real-ESRGAN": os.path.join(
        experiment_dir,
        "realesrgan.mp4"
    ),
    "Final": os.path.join(
        experiment_dir,
        "final.mp4"
    ),
}

for name, path in paths.items():

    cap = cv2.VideoCapture(path)

    fps = cap.get(cv2.CAP_PROP_FPS)
    frames = int(cap.get(cv2.CAP_PROP_FRAME_COUNT))
    w = int(cap.get(cv2.CAP_PROP_FRAME_WIDTH))
    h = int(cap.get(cv2.CAP_PROP_FRAME_HEIGHT))

    duration = frames / fps if fps > 0 else 0

    print("=" * 50)
    print(name)
    print("path     :", path)
    print("size     :", (w, h))
    print("fps      :", fps)
    print("frames   :", frames)
    print("duration :", duration, "sec")

    # 실제로 끝까지 decode 가능한 프레임 수도 확인
    decoded = 0

    while True:
        ret, frame = cap.read()

        if not ret:
            break

        decoded += 1

    print("decoded  :", decoded)

    cap.release()

LR
path     : /content/drive/MyDrive/KSY/capstone/results/vid/00_low_resolution_video.mp4
size     : (240, 134)
fps      : 30.0
frames   : 348
duration : 11.6 sec
decoded  : 348
Real-ESRGAN
path     : /content/drive/MyDrive/KSY/capstone/results/vid/realesrgan.mp4
size     : (960, 540)
fps      : 30.0
frames   : 348
duration : 11.6 sec
decoded  : 348
Final
path     : /content/drive/MyDrive/KSY/capstone/results/vid/final.mp4
size     : (960, 540)
fps      : 30.0
frames   : 348
duration : 11.6 sec
decoded  : 348


In [ ]:
# ============================================================
# SAVED RESULT 3-WAY VISUALIZATION
#
# Lanczos | Real-ESRGAN | Proposed
#
# 기존 결과 재처리 X
# 저장된 영상만 불러와서 비교 영상 생성
# ============================================================

import os
import cv2
import base64
from IPython.display import display, HTML


# ------------------------------------------------------------
# 이미 process_video()에서 만들어진 폴더 사용
# ------------------------------------------------------------

lr_path = os.path.join(
    experiment_dir,
    "00_low_resolution_video.mp4"
)

esrgan_path = os.path.join(
    experiment_dir,
    "realesrgan.mp4"
)

proposed_path = os.path.join(
    experiment_dir,
    "final.mp4"
)

comparison_path = os.path.join(
    experiment_dir,
    "comparison_3way.mp4"
)


# ------------------------------------------------------------
# 저장된 영상 열기
# ------------------------------------------------------------

cap_lr = cv2.VideoCapture(lr_path)
cap_esrgan = cv2.VideoCapture(esrgan_path)
cap_proposed = cv2.VideoCapture(proposed_path)

if not cap_lr.isOpened():
    raise RuntimeError(f"열기 실패: {lr_path}")

if not cap_esrgan.isOpened():
    raise RuntimeError(f"열기 실패: {esrgan_path}")

if not cap_proposed.isOpened():
    raise RuntimeError(f"열기 실패: {proposed_path}")


# ------------------------------------------------------------
# FPS
# ------------------------------------------------------------

fps = cap_proposed.get(cv2.CAP_PROP_FPS)

if fps <= 0:
    fps = 30.0


# ------------------------------------------------------------
# 비교용 패널 크기
#
# 640 x 360 × 3
# = 1920 x 360
# ------------------------------------------------------------

PANEL_W = 640
PANEL_H = 360

comparison_w = PANEL_W * 3
comparison_h = PANEL_H


# ------------------------------------------------------------
# Writer
# ------------------------------------------------------------

fourcc = cv2.VideoWriter_fourcc(*"mp4v")

writer = cv2.VideoWriter(
    comparison_path,
    fourcc,
    fps,
    (comparison_w, comparison_h)
)

if not writer.isOpened():
    raise RuntimeError("comparison VideoWriter 생성 실패")


# ------------------------------------------------------------
# 제목 함수
# ------------------------------------------------------------

def add_title(img, title):

    img = img.copy()

    # 제목 가독성을 위한 검은 배경
    cv2.rectangle(
        img,
        (0, 0),
        (PANEL_W, 55),
        (0, 0, 0),
        -1
    )

    cv2.putText(
        img,
        title,
        (20, 38),
        cv2.FONT_HERSHEY_SIMPLEX,
        0.9,
        (255, 255, 255),
        2,
        cv2.LINE_AA
    )

    return img


# ------------------------------------------------------------
# 저장된 영상 → 3분할
# ------------------------------------------------------------

frame_idx = 0

while True:

    ret_lr, frame_lr = cap_lr.read()
    ret_esr, frame_esr = cap_esrgan.read()
    ret_prop, frame_prop = cap_proposed.read()

    if not (
        ret_lr
        and ret_esr
        and ret_prop
    ):
        break


    # ========================================================
    # ① 기존 방식
    #
    # 저장된 480×270 LR
    #       ↓
    # Lanczos ×4 개념
    #
    # 비교 화면 크기로 바로 Lanczos 확대
    # ========================================================

    frame_lanczos = cv2.resize(
        frame_lr,
        (PANEL_W, PANEL_H),
        interpolation=cv2.INTER_LANCZOS4
    )


    # ========================================================
    # ② Real-ESRGAN
    # ========================================================

    frame_esr = cv2.resize(
        frame_esr,
        (PANEL_W, PANEL_H),
        interpolation=cv2.INTER_AREA
    )


    # ========================================================
    # ③ Proposed
    # ========================================================

    frame_prop = cv2.resize(
        frame_prop,
        (PANEL_W, PANEL_H),
        interpolation=cv2.INTER_AREA
    )


    # ========================================================
    # 제목
    # ========================================================

    frame_lanczos = add_title(
        frame_lanczos,
        "Lanczos"
    )

    frame_esr = add_title(
        frame_esr,
        "Real-ESRGAN"
    )

    frame_prop = add_title(
        frame_prop,
        "Proposed"
    )


    # ========================================================
    # 3분할
    # ========================================================

    comparison = cv2.hconcat([
        frame_lanczos,
        frame_esr,
        frame_prop
    ])


    writer.write(comparison)

    frame_idx += 1

    print(
        f"\rCreating 3-way visualization: {frame_idx}",
        end=""
    )


# ------------------------------------------------------------
# Release
# ------------------------------------------------------------

cap_lr.release()
cap_esrgan.release()
cap_proposed.release()
writer.release()


print()
print()
print("3-WAY VIDEO SAVED:")
print(comparison_path)


# ============================================================
# COLAB에서 무한 반복 재생
# ============================================================

with open(comparison_path, "rb") as f:
    video_base64 = base64.b64encode(
        f.read()
    ).decode("utf-8")


display(
    HTML(f"""
    <div style="
        width:100%;
        text-align:center;
    ">

        <video
            autoplay
            loop
            muted
            controls
            playsinline
            style="
                width:100%;
                max-width:1200px;
                height:auto;
            "
        >

            <source
                src="data:video/mp4;base64,{video_base64}"
                type="video/mp4"
            >

        </video>

    </div>
    """)
)

Creating 3-way visualization: 348

3-WAY VIDEO SAVED:
/content/drive/MyDrive/KSY/capstone/results/vid/comparison_3way.mp4


In [ ]:
# ============================================================
# COLAB - 저장된 comparison_3way.mp4 무한 반복 재생
#
# - 영상 재처리 X
# - base64 X
# - Google Drive 경로 직접 HTML에 넣기 X
# - Colab 파일 서버 URL 사용
# ============================================================

import os
from google.colab import output
from IPython.display import display, HTML


# ------------------------------------------------------------
# 1. 실제 저장된 비교 영상 확인
# ------------------------------------------------------------

video_path = os.path.abspath(
    os.path.join(
        experiment_dir,
        "comparison_3way.mp4"
    )
)

if not os.path.isfile(video_path):
    raise FileNotFoundError(
        f"비교 영상을 찾을 수 없습니다:\n{video_path}"
    )

file_size = os.path.getsize(video_path)

if file_size == 0:
    raise RuntimeError(
        f"영상 파일이 비어 있습니다:\n{video_path}"
    )

print("VIDEO PATH :", video_path)
print("FILE SIZE  :", f"{file_size / 1024 / 1024:.2f} MB")


# ------------------------------------------------------------
# 2. Colab이 접근할 수 있도록 /content 아래에 링크 생성
#
# Drive에 있는 파일을 복사하지 않고 symbolic link만 생성
# ------------------------------------------------------------

serve_dir = "/content/colab_video_player"
os.makedirs(serve_dir, exist_ok=True)

serve_path = os.path.join(
    serve_dir,
    "comparison_3way.mp4"
)

if os.path.lexists(serve_path):
    os.remove(serve_path)

os.symlink(
    video_path,
    serve_path
)


# ------------------------------------------------------------
# 3. Colab 로컬 HTTP 서버 시작
# ------------------------------------------------------------

PORT = 8765

get_ipython().system_raw(
    f"python3 -m http.server {PORT} "
    f"--directory '{serve_dir}' "
    f">/tmp/video_server.log 2>&1 &"
)


# ------------------------------------------------------------
# 4. Colab proxy URL 획득
# ------------------------------------------------------------

video_url = (
    output.eval_js(
        f"google.colab.kernel.proxyPort({PORT})"
    )
    + "comparison_3way.mp4"
)

print("VIDEO URL  :", video_url)


# ------------------------------------------------------------
# 5. 실제 MP4 URL을 video 태그로 재생
#
# loop = 무한 반복
# autoplay + muted = 브라우저 자동재생 허용
# ------------------------------------------------------------

html = """
<div style="
    width:100%;
    text-align:center;
">

    <video
        id="comparison_player"
        src="__VIDEO_URL__"
        autoplay
        loop
        muted
        controls
        playsinline
        preload="auto"
        style="
            width:100%;
            max-width:1200px;
            height:auto;
        "
    >
    </video>

</div>

<script>
(function () {

    const video =
        document.getElementById("comparison_player");

    video.loop = true;
    video.muted = true;

    video.addEventListener(
        "canplay",
        function () {
            video.play().catch(function () {});
        }
    );

    video.addEventListener(
        "ended",
        function () {
            video.currentTime = 0;
            video.play().catch(function () {});
        }
    );

})();
</script>
"""

html = html.replace(
    "__VIDEO_URL__",
    video_url
)

display(
    HTML(html)
)

VIDEO PATH : /content/drive/MyDrive/KSY/capstone/results/제목 없는 디자인 (1) (2)/comparison_3way.mp4
FILE SIZE  : 13.22 MB
VIDEO URL  : https://8765-gpu-t4-s-kkb-usw4a1-14s82hpbenv9-a.us-west4-1.prod.colab.devcomparison_3way.mp4
